# 05 — Translation Agreement and Disagreement

Notebook 04 established that exact agreement is uncommon and prompt-sensitive. Here I ask a broader question: **when services disagree, how extensive is that disagreement, what form does it take, and which observable conditions are associated with greater stability?**

I use multilingual embeddings as one diagnostic layer rather than as a substitute for linguistic judgment. Exact normalized strings preserve visible lexical alternatives; cosine distance can show when non-identical outputs nevertheless occupy nearby regions of an embedding model's representation. I then combine those measurements with disagreement shape, service-group alignment, prompt trajectories, Wikipedia evidence, source retention, and script signals.

The notebook proceeds in two stages:

1. **Embedding diagnostics** measure per-language dispersion and cross-service distance in the original 384-dimensional space. UMAP is used only to visualize how script and other surface features organize the model's representation.
2. **Multidimensional patterns** distinguish the degree of string variation from its cluster shape, participants, prompt trajectory, and technical context.

This notebook reports descriptive associations, not causal drivers or translation correctness. A tight cluster may reflect a stable equivalent, shared borrowing, or common model behavior. A wide cluster may reflect legitimate alternatives, uneven language knowledge, or fabrication.

**Exclusion tier: Tier 2 — Translation Analysis** (see [public_docs/exclusion_strategy.md](../public_docs/exclusion_strategy.md))

Term-error flags (`has_mixed_script`, `has_placeholder_term`, `has_repetition_loop`, `has_extreme_term_length`, `has_unicode_escape`) and manual `exclude_translation=True` entries drop individual language × service rows before embedding. Source retention, script disagreement, and other contextual signals remain available for analysis.


## 5.1 Setup & Data Load

In [1]:
import os
import sys
import warnings
from pathlib import Path

import numpy as np
import pandas as pd
import altair as alt

warnings.filterwarnings('ignore')
alt.data_transformers.disable_max_rows()

PROJECT_ROOT = Path('..')
if not (PROJECT_ROOT / 'scripts' / 'utils.py').exists():
    PROJECT_ROOT = Path('.')
sys.path.insert(0, str(PROJECT_ROOT))
from scripts.utils import read_csv_file, get_language_family, save_chart
from scripts.review.analyze_scripts import detect_dominant_script

DATA_DIR = PROJECT_ROOT / "datasets"
TERM      = 'Digital Humanities'
TERM_SLUG = TERM.lower().replace(' ', '_')
EVAL_DIR  = os.path.join(DATA_DIR, 'translated_terms', TERM_SLUG, 'evaluation')

CACHE_DIR = PROJECT_ROOT / 'notebooks' / 'eda_cache'
CACHE_DIR.mkdir(exist_ok=True)
FIGURE_DIR = PROJECT_ROOT / 'docs' / 'papers' / 'translation-to-transmogrification' / 'figures' / 'analysis'
FIGURE_DIR.mkdir(parents=True, exist_ok=True)

LLM_SERVICES = ['claude', 'openai', 'gemini', 'deepseek', 'llama', 'gemma', 'qwen', 'mistral']
ALL_VARIANTS = ['minimal', 'fluent_speaker', 'github_searcher', 'judge']
EMBED_MODEL  = 'paraphrase-multilingual-MiniLM-L12-v2'





Retrieving translation pipeline data directory path...

DATA_DIR:  ../datasets
EVAL_DIR:  ../datasets/translated_terms/digital_humanities/evaluation
Cache:     ../notebooks/eda_cache


In [2]:
# Load the across_variant_detail CSV — same data file 04 reads from. This gives us one row per (language × service) with a best_candidate translation already resolved across prompt variants.
detail_path = os.path.join(EVAL_DIR, 'across_variant_detail.csv')
detail_df = read_csv_file(detail_path)

# Keep only rows where there is actually a translation to embed
trans_df = detail_df[detail_df['best_candidate'].notna()].copy()
trans_df['best_candidate'] = trans_df['best_candidate'].astype(str).str.strip()
trans_df = trans_df[trans_df['best_candidate'].str.len() > 0].reset_index(drop=True)

# Enrich with features we'll want for coloring
trans_df['script'] = trans_df['best_candidate'].apply(detect_dominant_script)
trans_df['trans_len'] = trans_df['best_candidate'].str.len()

# Wikipedia presence per language (from the Wikipedia service rows in the same CSV)
wiki_langs = set(
    detail_df[
        (detail_df['service'] == 'Wikipedia') &
        (detail_df['best_candidate'].notna()) &
        (detail_df['best_candidate'].astype(str).str.strip() != '')
    ]['language_code']
)
trans_df['has_wikipedia'] = trans_df['language_code'].isin(wiki_langs)

print(f'Total translation rows: {len(trans_df):,}')
print(f'Unique languages:       {trans_df["language_code"].nunique()}')
print(f'Languages with Wikipedia: {len(wiki_langs)}')
print(f'Services: {sorted(trans_df["service"].unique())}')

# ── Language count sanity check (pre-exclusion) ─────────────────────────────
_n = detail_df['language_code'].nunique()
print(f'\nLanguages loaded (pre-exclusion): {_n} (expected 881)')
if _n != 881:
    print(f'  ⚠ Expected 881 — re-run the translation pipeline or check for missing/duplicate language_code rows.')
else:
    print(f'  ✓ Count matches expected 881.')

Total translation rows: 7,539
Unique languages:       881
Languages with Wikipedia: 40
Services: ['Claude', 'DeepSeek', 'EasyNMT', 'Gemini', 'Gemma', 'Google Translate', 'Lingvanex', 'Llama', 'Mistral', 'OpenAI', 'Qwen', 'Wikipedia']

Languages loaded (pre-exclusion): 881 (expected 881)
  ✓ Count matches expected 881.


In [3]:
# ── Tier 2 exclusions ───────────────────────────────────────────────────────
EXCL_PATH  = os.path.join(EVAL_DIR, 'manual_exclusions.csv')
FLAGS_PATH = os.path.join(EVAL_DIR, 'automated_review_signals.csv')

quality_flags_df = read_csv_file(FLAGS_PATH)

TERM_ERROR_COLS = {
    'has_mixed_script':        'mixed_script_services',
    'has_placeholder_term':    'placeholder_term_services',
    'has_repetition_loop':     'repetition_loop_services',
    'has_extreme_term_length': 'extreme_term_length_services',
    'has_unicode_escape':      'unicode_escape_services',
}

# Build per-(language, service) drop set from term-error flags
term_error_pairs = set()
for flag_col, svc_col in TERM_ERROR_COLS.items():
    for _, row in quality_flags_df[quality_flags_df[flag_col] == True].iterrows():
        for svc in str(row.get(svc_col, '')).split(';'):
            svc = svc.strip()
            if svc and svc != 'nan':
                term_error_pairs.add((row['language_code'], svc))

# Manual exclude_translation=True
manual_drop_pairs = set()
if os.path.exists(EXCL_PATH):
    excl_df = read_csv_file(EXCL_PATH)
    whole = excl_df[excl_df['exclude_translation'] == True][['language_code', 'service']]
    manual_drop_pairs = set(zip(whole['language_code'], whole['service']))

all_drop_pairs = term_error_pairs | manual_drop_pairs

# Annotation flags to retain on trans_df
ANNOT_COLS = ['language_code', 'has_source_term', 'has_script_disagreement',
              'has_any_mixing', 'has_romanization', 'quality_flags', 'flag_count']
trans_df = trans_df.merge(quality_flags_df[ANNOT_COLS], on='language_code', how='left')

n_before = len(trans_df)
trans_df = trans_df[
    ~trans_df.apply(lambda r: (r['language_code'], r['service']) in all_drop_pairs, axis=1)
].copy().reset_index(drop=True)
n_after = len(trans_df)
print(f'Tier 2: {n_before - n_after} rows dropped ({n_before} → {n_after} translations)')
print(f'  term-error flags: {len(term_error_pairs)} pairs')
print(f'  manual drops    : {len(manual_drop_pairs)} pairs')


Tier 2: 185 rows dropped (7539 → 7354 translations)
  term-error flags: 185 pairs
  manual drops    : 96 pairs


In [4]:
# Quick look at the data we're about to embed
print('By service:')
print(trans_df.groupby('service').size().sort_values(ascending=False))
print('\nBy script (top 10):')
print(trans_df['script'].value_counts().head(10))
print('\nTranslation length distribution:')
print(trans_df['trans_len'].describe().round(1))

By service:
service
Claude              876
DeepSeek            875
OpenAI              869
Gemini              863
Mistral             859
Llama               852
Qwen                841
Gemma               831
Google Translate    242
Lingvanex           109
EasyNMT              97
Wikipedia            40
dtype: int64

By script (top 10):
script
Latin         5174
Cyrillic       479
Devanagari     399
Arabic         362
CJK            140
Other          104
Bengali         63
Myanmar         51
Japanese        44
Syriac          42
Name: count, dtype: int64

Translation length distribution:
count    7354.0
mean       20.3
std         7.2
min         1.0
25%        16.0
50%        19.0
75%        23.0
max        93.0
Name: trans_len, dtype: float64


## 5.2 Embed Translations

One embedding per translation string. These are generally short, so embedding is fast. We cache to disk so a kernel restart doesn't recompute.

Using the same multilingual model as the rationale notebook (`paraphrase-multilingual-MiniLM-L12-v2`). Scripts differ across languages––Latin, Cyrillic, Arabic, CJK, Devanagari––so a multilingual encoder is essential. The encoder will organize outputs partly by script, which is a feature, not a bug: it lets us see script structure as a check on the embedding's behavior.

In [5]:
from sentence_transformers import SentenceTransformer

model = SentenceTransformer(EMBED_MODEL)
print(f'Model loaded: {EMBED_MODEL}, dim={model.get_sentence_embedding_dimension()}')

'(MaxRetryError('HTTPSConnectionPool(host=\'huggingface.co\', port=443): Max retries exceeded with url: /sentence-transformers/paraphrase-multilingual-MiniLM-L12-v2/resolve/main/modules.json (Caused by NameResolutionError("<urllib3.connection.HTTPSConnection object at 0x129a8b4d0>: Failed to resolve \'huggingface.co\' (Name or service not known: huggingface.co using 1 resolver(s))"))'), '(Request ID: 5fb38150-fe3c-4cd7-bb41-2eec6d644ef4)')' thrown while requesting HEAD https://huggingface.co/sentence-transformers/paraphrase-multilingual-MiniLM-L12-v2/resolve/main/./modules.json
Retrying in 1s [Retry 1/5].
'(MaxRetryError("HTTPSConnectionPool(host='huggingface.co', port=443): Max retries exceeded with url: /sentence-transformers/paraphrase-multilingual-MiniLM-L12-v2/resolve/main/modules.json (Caused by ConnectTimeoutError(<urllib3.connection.HTTPSConnection object at 0x129bb9e50>, 'Connection to huggingface.co timed out. (connect timeout=10)'))"), '(Request ID: 1fde7506-c278-49be-9b9a-6

Model loaded: paraphrase-multilingual-MiniLM-L12-v2, dim=384


In [6]:
def embed_with_cache(texts, cache_name, batch_size=128):
    '''Embed a list of strings, caching to disk keyed by cache_name.'''
    cache_path = CACHE_DIR / f'{cache_name}.npy'
    if cache_path.exists():
        cached = np.load(cache_path)
        if len(cached) == len(texts):
            print(f'Loading cached embeddings: {cache_path.name}')
            return cached
        print(f'Cache size mismatch ({len(cached)} vs {len(texts)}) — re-embedding.')
        cache_path.unlink()
    print(f'Encoding {len(texts):,} texts → {cache_path.name}')
    vecs = model.encode(
        texts,
        batch_size=batch_size,
        show_progress_bar=True,
        convert_to_numpy=True,
        normalize_embeddings=True,
    )
    np.save(cache_path, vecs)
    return vecs

trans_vecs = embed_with_cache(trans_df['best_candidate'].tolist(), 'translation_vecs')
print(f'Translation embeddings: {trans_vecs.shape}')

Loading cached embeddings: translation_vecs.npy
Translation embeddings: (7354, 384)


## 5.3 Embedding Space as a Diagnostic

Project everything into 2D once, then color four ways to see what organizes the space.

Expected: script type will dominate the global structure (writing systems are a strong visual feature of short strings). Wikipedia/no-Wikipedia should show up as a density difference rather than a clean split — the Wikipedia languages are a small minority (40 of 880) distributed across scripts.

In [7]:
import umap
import hdbscan

# One UMAP for the whole landscape; reused across all four colorings
reducer = umap.UMAP(
    n_neighbors=15,
    min_dist=0.1,
    n_components=2,
    metric='cosine',
    random_state=42,
)
coords = reducer.fit_transform(trans_vecs)
trans_df['umap_x'] = coords[:, 0]
trans_df['umap_y'] = coords[:, 1]
print('Projection complete.')

Projection complete.


In [8]:
# Four-panel plot: same coords, four color mappings
ax = dict(
    x=alt.X('umap_x:Q', title='UMAP-1', axis=alt.Axis(labels=False, ticks=False)),
    y=alt.Y('umap_y:Q', title='UMAP-2', axis=alt.Axis(labels=False, ticks=False)),
)
base = alt.Chart(trans_df).mark_circle(size=20, opacity=0.55)
tooltip = ['language_name:N', 'service:N', 'best_candidate:N', 'script:N']

# Keep only the most populated scripts in the legend; collapse the rest
top_scripts = trans_df['script'].value_counts().head(8).index.tolist()
trans_df['script_plot'] = trans_df['script'].where(trans_df['script'].isin(top_scripts), 'Other')
trans_df['wikipedia_label'] = np.where(trans_df['has_wikipedia'], 'Wikipedia term', 'No Wikipedia term')

script_plot = (
    alt.Chart(trans_df).mark_circle(size=20, opacity=0.55)
    .encode(**ax, color=alt.Color('script_plot:N', title='Script',
                                   scale=alt.Scale(scheme='tableau10')),
            tooltip=tooltip)
    .properties(width=340, height=340, title='Colored by dominant script')
)

service_plot = base.encode(
    **ax,
    color=alt.Color('service:N', scale=alt.Scale(scheme='category10'), title='Service'),
    tooltip=tooltip,
).properties(width=340, height=340, title='Colored by service')

wiki_plot = base.encode(
    **ax,
    color=alt.Color('wikipedia_label:N',
                    scale=alt.Scale(domain=['Wikipedia term', 'No Wikipedia term'], range=['#e45756', '#a9a9a9']),
                    title='Wikipedia evidence'),
    tooltip=tooltip,
).properties(width=340, height=340, title='Colored by Wikipedia presence')

family_plot = base.encode(
    **ax,
    color=alt.Color('language_family:N', title='Language Family'),
    tooltip=tooltip,
).properties(width=340, height=340, title='Colored by language family')

global_translation_landscape_chart = alt.hconcat(script_plot, service_plot, wiki_plot).resolve_scale(color='independent')
display(global_translation_landscape_chart)
save_chart(global_translation_landscape_chart, FIGURE_DIR / 'global_translation_embedding_landscape.png')

alt.HConcatChart(...)

In [9]:
family_plot

alt.Chart(...)

## 5.4 Semantic Distance Beyond Exact Matching

For each language, I take the available LLM outputs and measure how tightly they cluster in embedding space. This provides a continuous complement to exact string comparison: non-identical strings may still occupy nearby regions of the multilingual embedding space.

I compute **mean pairwise cosine distance** among the LLM outputs per language. Lower values indicate tighter geometric clustering and higher values indicate greater dispersion. This is a diagnostic measurement, not a judgment about correctness or fabrication.

In [10]:
from scipy.spatial.distance import pdist

# Per-language: gather the LLM outputs and compute pairwise distance
llm_rows = trans_df[trans_df['service'].str.lower().isin(LLM_SERVICES)].copy()

scatter_rows = []
for (lang, term_src), g in llm_rows.groupby(['language_code', 'term_source']):
    if len(g) < 2:
        continue
    idxs = g.index.tolist()
    vecs = trans_vecs[idxs]
    # Mean pairwise cosine distance
    pairwise = pdist(vecs, metric='cosine')
    scatter_rows.append({
        'language_code': lang,
        'language_name': g['language_name'].iloc[0],
        'language_family': g['language_family'].iloc[0],
        'has_wikipedia': g['has_wikipedia'].iloc[0],
        'n_services': len(g),
        'mean_pairwise_distance': float(pairwise.mean()),
        'max_pairwise_distance': float(pairwise.max()),
    })

scatter_df = pd.DataFrame(scatter_rows)
projection_metrics_path = os.path.join(EVAL_DIR, 'translation_projection_language_metrics.csv')
scatter_df.to_csv(projection_metrics_path, index=False)
print("Saved per-language projection metrics.")
print(f'Languages with ≥2 LLM translations: {len(scatter_df):,}')
print(f'\nMean pairwise distance by Wikipedia presence:')
print(scatter_df.groupby('has_wikipedia')['mean_pairwise_distance']
        .agg(['mean', 'median', 'std', 'count']).round(3))

Saved per-language projection metrics: ../datasets/translated_terms/digital_humanities/evaluation/translation_projection_language_metrics.csv
Languages with ≥2 LLM translations: 881

Mean pairwise distance by Wikipedia presence:
                mean  median    std  count
has_wikipedia                             
False          0.392   0.423  0.145    841
True           0.158   0.152  0.115     40


In [11]:
# Histogram: distribution of mean pairwise distance, split by Wikipedia
scatter_df['wikipedia_label'] = np.where(scatter_df['has_wikipedia'], 'Wikipedia term', 'No Wikipedia term')
wikipedia_consensus_chart = alt.Chart(scatter_df).mark_bar(opacity=0.7).encode(
    x=alt.X('mean_pairwise_distance:Q', bin=alt.Bin(maxbins=40),
            title='Mean pairwise cosine distance among LLM outputs'),
    y=alt.Y('count():Q', title='Number of languages'),
    color=alt.Color('wikipedia_label:N',
                    scale=alt.Scale(domain=['Wikipedia term', 'No Wikipedia term'], range=['#e45756', '#a9a9a9']),
                    title='Wikipedia evidence'),
    tooltip=['wikipedia_label:N', 'count():Q'],
).properties(
    width=640, height=320,
    title='Translation consensus by Wikipedia presence (lower = more consensus)',
)
display(wikipedia_consensus_chart)
save_chart(wikipedia_consensus_chart, FIGURE_DIR / 'translation_consensus_by_wikipedia_presence.png')

alt.Chart(...)

In [12]:
# These extremes identify candidates for close reading; embedding distance alone does not explain why they cluster or diverge.
print('Most CONSENSUAL (tightest service cluster):')
print(scatter_df.nsmallest(15, 'mean_pairwise_distance')[
    ['language_name', 'language_family', 'has_wikipedia', 'mean_pairwise_distance']
].to_string(index=False))

print('\nMost DIVERGENT (loosest service cluster):')
print(scatter_df.nlargest(15, 'mean_pairwise_distance')[
    ['language_name', 'language_family', 'has_wikipedia', 'mean_pairwise_distance']
].to_string(index=False))

Most CONSENSUAL (tightest service cluster):
       language_name         language_family  has_wikipedia  mean_pairwise_distance
  Catalan; Valencian Indo-European languages           True            0.000000e+00
          Portuguese Indo-European languages           True            0.000000e+00
  Spanish; Castilian Indo-European languages           True            2.220446e-16
              Korean        Language isolate           True            4.720034e-14
               Latin Indo-European languages           True            2.513856e-03
              Bihari Indo-European languages          False            5.583761e-03
             Swedish Indo-European languages           True            1.399507e-02
              Syriac  Afro-Asiatic languages          False            1.758950e-02
            Corsican Indo-European languages          False            2.055671e-02
         Interlingua    Artificial languages          False            2.375391e-02
            Cherokee            

## 5.5 Service-Level Dispersion

For each service, what is the spread of its translation outputs in embedding space? A service with a tight distribution is producing a narrow range of outputs (possibly because it defaults to a narrow translation strategy — e.g., always loanword). A service with a wide distribution is either doing more varied translation work (ideal) or hallucinating more varied outputs (problematic). To be clear, you can't tell from the distribution alone, but the width itself is visible.

In [13]:
# Per service: distance from service's own centroid
service_rows = []
for svc, g in llm_rows.groupby('service'):
    idxs = g.index.tolist()
    vecs = trans_vecs[idxs]
    centroid = vecs.mean(axis=0, keepdims=True)
    from scipy.spatial.distance import cdist
    dists = cdist(vecs, centroid, metric='cosine').flatten()
    for d in dists:
        service_rows.append({'service': svc, 'dist_from_centroid': float(d)})

service_spread_df = pd.DataFrame(service_rows)
print('Spread from service centroid (higher = wider output distribution):')
print(service_spread_df.groupby('service')['dist_from_centroid']
        .agg(['mean', 'median', 'std']).round(3))

Spread from service centroid (higher = wider output distribution):
           mean  median    std
service                       
Claude    0.284   0.217  0.146
DeepSeek  0.288   0.246  0.128
Gemini    0.271   0.200  0.152
Gemma     0.307   0.299  0.082
Llama     0.318   0.301  0.090
Mistral   0.304   0.283  0.146
OpenAI    0.225   0.116  0.179
Qwen      0.310   0.290  0.117


In [14]:
service_spread_chart = alt.Chart(service_spread_df).mark_boxplot(extent='min-max').encode(
    x=alt.X('service:N', title=None),
    y=alt.Y('dist_from_centroid:Q', title='Distance from service centroid'),
    color=alt.Color('service:N', legend=None, scale=alt.Scale(scheme='category10')),
).properties(
    width=400, height=320,
    title='Translation output spread by service',
)
display(service_spread_chart)
save_chart(service_spread_chart, FIGURE_DIR / 'translation_output_spread_by_service.png')

alt.Chart(...)

## 5.6 Cross-Service Distance Matrix

Zooming out: for each pair of services, what is the mean distance between their outputs for the same language? This is the translation-space analog of the rationale-pairwise similarity metric.

In [15]:
# Pair-wise mean distance between services for the same language
from scipy.spatial.distance import cdist as _cdist

# Use actual service names from llm_rows (capitalized: 'Claude', 'Gemini', ...)
# NOT LLM_SERVICES (lowercase), which would cause all svc_to_idx lookups to miss.
SVC = sorted(llm_rows['service'].unique())
n = len(SVC)
dist_matrix = np.zeros((n, n))

for (lang, term_src), g in llm_rows.groupby(['language_code', 'term_source']):
    svc_to_idx = {r['service']: i for i, r in g.iterrows()}
    for i, s1 in enumerate(SVC):
        for j, s2 in enumerate(SVC):
            if s1 in svc_to_idx and s2 in svc_to_idx and i != j:
                v1 = trans_vecs[svc_to_idx[s1]:svc_to_idx[s1]+1]
                v2 = trans_vecs[svc_to_idx[s2]:svc_to_idx[s2]+1]
                dist_matrix[i, j] += _cdist(v1, v2, metric='cosine').item()

# Normalize by count of languages where both services have data
counts = np.zeros((n, n))
for (lang, term_src), g in llm_rows.groupby(['language_code', 'term_source']):
    services_here = set(g['service'].tolist())
    for i, s1 in enumerate(SVC):
        for j, s2 in enumerate(SVC):
            if s1 in services_here and s2 in services_here and i != j:
                counts[i, j] += 1

mean_distances = np.where(counts > 0, dist_matrix / np.where(counts == 0, 1, counts), np.nan)

# Long-format for Altair heatmap
heatmap_rows = []
for i, s1 in enumerate(SVC):
    for j, s2 in enumerate(SVC):
        if i != j:
            heatmap_rows.append({
                'service_a': s1,
                'service_b': s2,
                'mean_distance': mean_distances[i, j],
                'n_languages': int(counts[i, j]),
            })
heatmap_df = pd.DataFrame(heatmap_rows)

cross_service_distance_chart = alt.Chart(heatmap_df).mark_rect().encode(
    x=alt.X('service_a:N', title=None),
    y=alt.Y('service_b:N', title=None),
    color=alt.Color('mean_distance:Q', scale=alt.Scale(scheme='reds')),
    tooltip=['service_a:N', 'service_b:N', 'mean_distance:Q', 'n_languages:Q'],
).properties(
    width=300, height=300,
    title='Pairwise cosine distance between service translations',
)
display(cross_service_distance_chart)
save_chart(cross_service_distance_chart, FIGURE_DIR / 'cross_service_translation_distance_matrix.png')

alt.Chart(...)

In [16]:
heatmap_df

,service_a,service_b,mean_distance,n_languages
0,Claude,DeepSeek,0.263356,870
1,Claude,Gemini,0.270370,860
2,Claude,Gemma,0.385909,826
3,Claude,Llama,0.421892,848
4,Claude,Mistral,0.409881,856
5,Claude,OpenAI,0.246719,864
6,Claude,Qwen,0.423185,836
7,DeepSeek,Claude,0.263356,870
8,DeepSeek,Gemini,0.272594,860
9,DeepSeek,Gemma,0.371513,825


## 5.7 Build the Multidimensional Pattern Table

`build_disagreement_patterns.py` combines the neutral comparison table with the per-language embedding metrics produced above, prompt-level translations, service-group patterns, and review signals. It writes `disagreement_patterns.csv`, which remains the reusable input for the later interpretive synthesis.


In [17]:
import subprocess

PATTERN_PATH = os.path.join(EVAL_DIR, 'disagreement_patterns.csv')
proc = subprocess.run(
    [sys.executable, 'scripts/analysis/build_disagreement_patterns.py'],
    cwd=str(PROJECT_ROOT), capture_output=True, text=True,
)
print(proc.stdout)
if proc.returncode:
    print(proc.stderr)
    raise RuntimeError('build_disagreement_patterns.py failed')

patterns = read_csv_file(PATTERN_PATH)
assert len(patterns) == 881
print(f'{len(patterns):,} language-code rows; {len(patterns.columns)} pattern and evidence columns')


Retrieving translation pipeline data directory path...
Saved 881 rows x 61 columns -> ../datasets/translated_terms/digital_humanities/evaluation/disagreement_patterns.csv
Saved 20661 rationale rows -> ../datasets/translated_terms/digital_humanities/evaluation/rationale_signal_detail.csv
disagreement_shape
fragmented_disagreement            746
dominant_form_with_alternatives    128
unanimous                            5
near_unanimous_with_outlier          2

881 language-code rows; 61 pattern and evidence columns


## 5.8 Degree and Shape Are Different Questions

The three comparison statuses measure how far strings differ. `disagreement_shape` instead uses the sizes of exact normalized-form clusters:

- **Unanimous**: one form across all usable services.
- **Near-unanimous with outlier**: all but one service share a form.
- **Dominant form with alternatives**: at least half of services share one form.
- **Two-cluster split**: two comparably sized form clusters.
- **Fragmented disagreement**: no form reaches half of the available services.

This distinction separates broad fragmentation from cases where apparent variation is driven by one or two services. The table below summarizes the complementary measurements I use to interpret those exact-form patterns. Exact-form, cluster, service, prompt, script, and external-evidence measures inform the analysis reported in the article. I retain embedding distance as an exploratory measure for identifying potentially related non-identical forms, with the fuller analysis documented in this notebook and reserved for planned comparative work across disciplinary terms. None of these dimensions independently establishes whether a translation is correct.

In [18]:
from great_tables import GT

disagreement_dimensions_df = pd.DataFrame([
    {
        'dimension': 'Exact normalized form',
        'measurement': 'Identical outputs after limited normalization',
        'interpretive_purpose': 'Identifies literal convergence while preserving substantive spelling, diacritic, and script differences.',
    },
    {
        'dimension': 'Embedding distance',
        'measurement': 'Exploratory proximity among non-identical translations',
        'interpretive_purpose': 'Identifies potentially related variants for further analysis; cross-term and encoder validation are reserved for planned comparative work.',
    },
    {
        'dimension': 'Cluster shape',
        'measurement': 'Number, size, and concentration of recurring exact forms',
        'interpretive_purpose': 'Separates dominant forms with alternatives from broadly fragmented disagreement.',
    },
    {
        'dimension': 'Service-group alignment',
        'measurement': 'Agreement within and across API LLMs, local LLMs, and direct services',
        'interpretive_purpose': 'Locates convergence or fragmentation within particular technical infrastructures.',
    },
    {
        'dimension': 'Prompt trajectory',
        'measurement': 'Changes within the same service across prompt conditions',
        'interpretive_purpose': 'Identifies prompt-stable and prompt-sensitive translations.',
    },
    {
        'dimension': 'Script behavior',
        'measurement': 'Expected script, script mixing, and transliteration patterns',
        'interpretive_purpose': 'Distinguishes lexical variation from orthographic or script-level differences.',
    },
    {
        'dimension': 'External and technical evidence',
        'measurement': 'Wikipedia presence, source retention, and automated review signals',
        'interpretive_purpose': 'Contextualizes convergence and flags outputs for review without validating them.',
    },
])

disagreement_dimensions_table = (
    GT(disagreement_dimensions_df)
    .tab_header(
        title='Dimensions of Translation Disagreement',
        subtitle='The article emphasizes transparent form and provenance measures; embedding distance remains exploratory.',
    )
    .cols_label(
        dimension='Dimension',
        measurement='What it measures',
        interpretive_purpose='Interpretive purpose',
    )
    .cols_width(
        dimension='205px',
        measurement='360px',
        interpretive_purpose='500px',
    )
    .tab_options(
        column_labels_font_weight='bold',
        column_labels_vlines_style='solid',
        column_labels_vlines_width='1px',
        column_labels_vlines_color='#A9A9A9',
        table_body_vlines_style='solid',
        table_body_vlines_width='1px',
        table_body_vlines_color='#D0D0D0',
    )
    .tab_source_note(
        source_note=(
            'Source: Coding DH multidimensional disagreement analysis. Exact-form, cluster, service, prompt, script, and external-evidence measures inform the present article. '
            'Embedding distance is documented in the notebooks as exploratory work for a planned comparative study across disciplinary terms. '
            'No dimension independently establishes translation correctness.'
        )
    )
)

display(disagreement_dimensions_table)
disagreement_dimensions_table_path = FIGURE_DIR / 'translation_disagreement_dimensions_table.png'
disagreement_dimensions_table.gtsave(str(disagreement_dimensions_table_path))
print("Saved article table figure.")

GT(_tbl_data=                         dimension  \
0            Exact normalized form   
1               Embedding distance   
2                    Cluster shape   
3          Service-group alignment   
4                Prompt trajectory   
5                  Script behavior   
6  External and technical evidence   

                                         measurement  \
0      Identical outputs after limited normalization   
1  Exploratory proximity among non-identical tran...   
2  Number, size, and concentration of recurring e...   
3  Agreement within and across API LLMs, local LL...   
4  Changes within the same service across prompt ...   
5  Expected script, script mixing, and transliter...   
6  Wikipedia presence, source retention, and auto...   

                                interpretive_purpose  
0  Identifies literal convergence while preservin...  
1  Identifies potentially related variants for fu...  
2  Separates dominant forms with alternatives fro...  
3  Locates convergence or fragmentation within pa...  
4  Identifies prompt-stable and prompt-sensitive ...  
5  Distinguishes lexical variation from orthograp...  
6  Contextualizes convergence and flags outputs f...  , _body=<great_tables._gt_data.Body object at 0x141892510>, _boxhead=Boxhead([ColInfo(var='dimension', type=<ColInfoTypeEnum.default: 1>, column_label='Dimension', column_align='left', column_width='205px'), ColInfo(var='measurement', type=<ColInfoTypeEnum.default: 1>, column_label='What it measures', column_align='left', column_width='360px'), ColInfo(var='interpretive_purpose', type=<ColInfoTypeEnum.default: 1>, column_label='Interpretive purpose', column_align='left', column_width='500px')]), _stub=<great_tables._gt_data.Stub object at 0x141892270>, _spanners=Spanners([]), _heading=Heading(title='Dimensions of Translation Disagreement', subtitle='The article emphasizes transparent form and provenance measures; embedding distance remains exploratory.', preheader=None), _stubhead=None, _summary_rows=<great_tables._gt_data.SummaryRows object at 0x141892900>, _summary_rows_grand=<great_tables._gt_data.SummaryRows object at 0x1418d6e90>, _source_notes=['Source: Coding DH multidimensional disagreement analysis. Exact-form, cluster, service, prompt, script, and external-evidence measures inform the present article. Embedding distance is documented in the notebooks as exploratory work for a planned comparative study across disciplinary terms. No dimension independently establishes translation correctness.'], _footnotes=[], _styles=[], _locale=<great_tables._gt_data.Locale object at 0x141892a50>, _formats=[], _substitutions=[], _col_merge=[], _transforms=[], _options=Options(table_id=OptionsInfo(scss=False, category='table', type='value', value=None), table_caption=OptionsInfo(scss=False, category='table', type='value', value=None), table_width=OptionsInfo(scss=True, category='table', type='px', value='auto'), table_layout=OptionsInfo(scss=True, category='table', type='value', value='fixed'), table_margin_left=OptionsInfo(scss=True, category='table', type='px', value='auto'), table_margin_right=OptionsInfo(scss=True, category='table', type='px', value='auto'), table_background_color=OptionsInfo(scss=True, category='table', type='value', value='#FFFFFF'), table_additional_css=OptionsInfo(scss=False, category='table', type='values', value=[]), table_font_names=OptionsInfo(scss=False, category='table', type='values', value=['-apple-system', 'BlinkMacSystemFont', 'Segoe UI', 'Roboto', 'Oxygen', 'Ubuntu', 'Cantarell', 'Helvetica Neue', 'Fira Sans', 'Droid Sans', 'Arial', 'sans-serif']), table_font_size=OptionsInfo(scss=True, category='table', type='px', value='16px'), table_font_weight=OptionsInfo(scss=True, category='table', type='value', value='normal'), table_font_style=OptionsInfo(scss=True, category='table', type='value', value='normal'), table_font_color=OptionsInfo(scss=True, category='table', type='value', value='#333333'), table_font_color_light=

Saved article table figure: ../public_docs/papers/translation-to-transmogrification/figures/analysis/translation_disagreement_dimensions_table.png


In [19]:
SHAPE_ORDER = [
    'unanimous', 'near_unanimous_with_outlier',
    'dominant_form_with_alternatives', 'two_cluster_split',
    'fragmented_disagreement', 'insufficient_comparison',
]
SHAPE_LABELS = {s: s.replace('_', ' ').title() for s in SHAPE_ORDER}

shape_counts = patterns['disagreement_shape'].value_counts().rename_axis('disagreement_shape').reset_index(name='languages')
shape_counts['label'] = shape_counts['disagreement_shape'].map(SHAPE_LABELS)
shape_counts['pct'] = shape_counts['languages'] / len(patterns)
shape_counts['annotation'] = shape_counts.apply(lambda r: f"{r['languages']:,} ({r['pct']:.1%})", axis=1)
display(shape_counts)

shape_bar = alt.Chart(shape_counts).mark_bar().encode(
    y=alt.Y('label:N', sort=[SHAPE_LABELS[s] for s in SHAPE_ORDER], title=None),
    x=alt.X('languages:Q', title='Language-code rows'),
    color=alt.Color('disagreement_shape:N', legend=None, scale=alt.Scale(scheme='tableau10')),
)
shape_text = shape_bar.mark_text(align='left', dx=5, color='black').encode(text='annotation:N')
shape_chart = (shape_bar + shape_text).properties(
    width=650, height=230, title='Shape of cross-service translation disagreement'
).configure_view(stroke=None)
display(shape_chart)
save_chart(shape_chart, str(FIGURE_DIR / 'disagreement_shape_distribution.png'))

,disagreement_shape,languages,label,pct,annotation
0,fragmented_disagreement,746,Fragmented Disagreement,0.846765,746 (84.7%)
1,dominant_form_with_alternatives,128,Dominant Form With Alternatives,0.145289,128 (14.5%)
2,unanimous,5,Unanimous,0.005675,5 (0.6%)
3,near_unanimous_with_outlier,2,Near Unanimous With Outlier,0.002270,2 (0.2%)


alt.LayerChart(...)

In [20]:
status_shape = patterns.groupby(['comparison_status', 'disagreement_shape']).size().reset_index(name='languages')
status_shape['share'] = status_shape.groupby('comparison_status')['languages'].transform(lambda s: s / s.sum())
status_shape['shape_label'] = status_shape['disagreement_shape'].map(SHAPE_LABELS)

status_shape_chart = alt.Chart(status_shape).mark_bar().encode(
    x=alt.X('comparison_status:N', title=None, axis=alt.Axis(labelAngle=0)),
    y=alt.Y('share:Q', title='Share within comparison status', axis=alt.Axis(format='%')),
    color=alt.Color('shape_label:N', title='Disagreement shape', scale=alt.Scale(scheme='tableau10')),
    order=alt.Order('share:Q', sort='descending'),
).properties(width=620, height=330, title='String distance and cluster shape capture different properties')
display(status_shape_chart)
save_chart(status_shape_chart, str(FIGURE_DIR / 'comparison_status_by_disagreement_shape.png'))

alt.Chart(...)

## 5.9 Who Aligns and Who Becomes an Outlier?

I compare exact-form concentration within API LLMs, local LLMs, machine-translation services, and all LLMs. The resulting service-group pattern does not rank those groups. It records whether agreement is concentrated in one part of the infrastructure and identifies singleton service outliers for close reading.

In [21]:
service_counts = patterns['service_group_pattern'].value_counts().rename_axis('service_group_pattern').reset_index(name='languages')
service_counts['label'] = (service_counts['service_group_pattern'].str.replace('_', ' ').str.title()
                           .str.replace('Api', 'API').str.replace('Llm', 'LLM'))
display(service_counts)

service_chart = alt.Chart(service_counts).mark_bar().encode(
    y=alt.Y('label:N', sort='-x', title=None),
    x=alt.X('languages:Q', title='Language-code rows'),
    color=alt.Color('service_group_pattern:N', legend=None, scale=alt.Scale(scheme='set2')),
).properties(width=620, height=220, title='Alignment within API and local LLM groups')
display(service_chart)
save_chart(service_chart, str(FIGURE_DIR / 'service_group_disagreement_patterns.png'))

print('Rows with an MT/LLM dominant-form split:', int(patterns['has_mt_llm_split'].sum()))
print('Rows with at least one singleton service outlier:', int(patterns['singleton_outlier_service_count'].gt(0).sum()))
display(patterns['singleton_outlier_services'].value_counts().head(15).rename_axis('outlier_services').reset_index(name='languages'))

,service_group_pattern,languages,label
0,api_and_local_fragmented,454,API And Local Fragmented
1,mixed_group_alignment,243,Mixed Group Alignment
2,api_aligned_local_fragmented,173,API Aligned Local Fragmented
3,api_and_local_aligned,10,API And Local Aligned
4,local_aligned_api_fragmented,1,Local Aligned API Fragmented


alt.Chart(...)

Rows with an MT/LLM dominant-form split: 11
Rows with at least one singleton service outlier: 129


,outlier_services,languages
0,Gemma; Llama; Mistral; Qwen,27
1,Llama; Mistral; Qwen,22
2,Mistral; Qwen,9
3,Gemma; Llama; Qwen,7
4,Llama; Qwen,6
5,DeepSeek; Llama; Mistral; Qwen,4
6,Gemma; Mistral; Qwen,4
7,EasyNMT; Llama; Mistral; Qwen,3
8,Google Translate; Llama; Mistral; Qwen,2
9,Gemma; Qwen,2


## 5.10 Prompt Trajectories

Prompt sensitivity is measured within each LLM service across the four prompt variants. The notebook also records cases where the GitHub prompt introduces source-term echoing that was absent from the minimal prompt, and whether the judge prompt reduces or increases the number of distinct LLM forms. Judge-induced convergence is descriptive: synthesis can harmonize outputs without making them more accurate.

In [22]:
judge_counts = patterns['judge_effect'].value_counts().rename_axis('judge_effect').reset_index(name='languages')
judge_counts['label'] = judge_counts['judge_effect'].str.replace('_', ' ').str.title()

judge_chart = alt.Chart(judge_counts).mark_bar().encode(
    y=alt.Y('label:N', sort='-x', title=None),
    x=alt.X('languages:Q', title='Language-code rows'),
    color=alt.Color('judge_effect:N', legend=None, scale=alt.Scale(scheme='tableau10')),
).properties(width=620, height=150, title='How the judge prompt changes cross-service form diversity')
display(judge_chart)
save_chart(judge_chart, str(FIGURE_DIR / 'judge_prompt_disagreement_effect.png'))

prompt_summary = patterns[[
    'prompt_stable_service_count', 'prompt_sensitive_service_count',
    'github_source_echo_service_count', 'minimal_unique_llm_forms', 'judge_unique_llm_forms',
]].describe().round(2)
display(prompt_summary)
print('Languages where GitHub framing introduces source echo:', int(patterns['github_source_echo_service_count'].gt(0).sum()))

embedding_chart = alt.Chart(patterns.dropna(subset=['mean_embedding_distance'])).mark_boxplot(size=35).encode(
    x=alt.X('disagreement_shape:N', sort=SHAPE_ORDER, title=None, axis=alt.Axis(labelAngle=325)),
    y=alt.Y('mean_embedding_distance:Q', title='Mean pairwise LLM embedding distance'),
    color=alt.Color('disagreement_shape:N', legend=None, scale=alt.Scale(scheme='tableau10')),
).properties(width=620, height=300, title='Embedding dispersion by exact-form disagreement shape')
display(embedding_chart)
save_chart(embedding_chart, str(FIGURE_DIR / 'embedding_dispersion_by_disagreement_shape.png'))

alt.Chart(...)

,prompt_stable_service_count,prompt_sensitive_service_count,github_source_echo_service_count,minimal_unique_llm_forms,judge_unique_llm_forms
count,881.00,881.00,881.00,881.00,881.00
mean,0.87,7.13,0.66,6.78,4.22
std,1.45,1.45,0.92,1.38,1.73
min,0.00,0.00,0.00,1.00,1.00
25%,0.00,7.00,0.00,6.00,3.00
50%,0.00,8.00,0.00,7.00,4.00
75%,1.00,8.00,1.00,8.00,5.00
max,8.00,8.00,5.00,8.00,8.00


Languages where GitHub framing introduces source echo: 373


alt.Chart(...)

### Prompt and Model Structure of Exact-Form Disagreement

The aggregate disagreement categories above describe language-level outcomes, but they do not assign those outcomes to one prompt or model. The next figure returns to the full experimental grid using exact normalized forms. The left panel holds the prompt constant and counts how many distinct forms the eight models produce. The right panel holds the model constant and asks how often its available prompts all produce different forms. This separates prompt effects from model-specific prompt sensitivity without treating either as evidence of correctness.


In [23]:
### Article figure: prompt and model structure of disagreement
from scripts.analysis.explore_confidence_within_variant import load_variant_df
from scripts.analysis.explore_disagreements import normalize

PROMPT_LABELS = {
    'minimal': 'Minimal',
    'fluent_speaker': 'Fluent Speaker',
    'github_searcher': 'GitHub Searcher',
    'judge': 'Judge',
}
PROMPT_COLORS = {
    'Minimal': '#4C78A8',
    'Fluent Speaker': '#F58518',
    'GitHub Searcher': '#E45756',
    'Judge': '#72B7B2',
}
SERVICE_LABELS = {
    'claude': 'Claude', 'openai': 'OpenAI', 'gemini': 'Gemini',
    'deepseek': 'DeepSeek', 'llama': 'Llama', 'gemma': 'Gemma',
    'qwen': 'Qwen', 'mistral': 'Mistral',
}
SERVICE_COLORS = {
    'Claude': '#4C78A8', 'OpenAI': '#F58518', 'Gemini': '#E45756',
    'DeepSeek': '#72B7B2', 'Llama': '#54A24B', 'Gemma': '#EECA3B',
    'Qwen': '#B279A2', 'Mistral': '#FF9DA6',
}

exact_grid_rows = []
for variant in ALL_VARIANTS:
    variant_df = load_variant_df(DATA_DIR, TERM_SLUG, variant)
    for _, row in variant_df.iterrows():
        language_code = row['language_code']
        for service_key, service_label in SERVICE_LABELS.items():
            column = f'{service_key}_translated_term'
            value = row.get(column)
            if pd.isna(value) or (language_code, service_label) in all_drop_pairs:
                continue
            value = str(value).strip()
            normalized = normalize(value)
            if not normalized:
                continue
            exact_grid_rows.append({
                'language_code': language_code,
                'variant': variant,
                'prompt': PROMPT_LABELS[variant],
                'service': service_label,
                'normalized_form': normalized,
            })

exact_grid = pd.DataFrame(exact_grid_rows)

# Hold prompt constant: how many forms do the available models produce?
prompt_diversity = (
    exact_grid.groupby(['language_code', 'variant', 'prompt'])
    .agg(available_models=('service', 'nunique'), distinct_forms=('normalized_form', 'nunique'))
    .reset_index()
)
prompt_order = [PROMPT_LABELS[v] for v in ALL_VARIANTS]
prompt_medians = (
    prompt_diversity.groupby('prompt', as_index=False)['distinct_forms'].median()
    .rename(columns={'distinct_forms': 'median_forms'})
)
prompt_medians['median_label'] = prompt_medians['median_forms'].map(lambda value: f'Median {value:g}')

prompt_box = alt.Chart(prompt_diversity).mark_boxplot(size=42, extent='min-max').encode(
    x=alt.X('distinct_forms:Q', title='Distinct normalized forms across available models',
            scale=alt.Scale(domain=[0.5, 8.5]), axis=alt.Axis(tickMinStep=1)),
    y=alt.Y('prompt:N', sort=prompt_order, title=None),
    color=alt.Color('prompt:N', legend=None,
                    scale=alt.Scale(domain=prompt_order,
                                    range=[PROMPT_COLORS[p] for p in prompt_order])),
).properties(width=430, height=210, title='Cross-model diversity within each prompt')

prompt_median_text = alt.Chart(prompt_medians).mark_text(
    align='left', dx=8, fontSize=12, fontWeight='bold', color='black'
).encode(
    x='median_forms:Q',
    y=alt.Y('prompt:N', sort=prompt_order),
    text='median_label:N',
)
prompt_panel = prompt_box + prompt_median_text

# Hold model constant across the three independent prompts. Restrict to
# complete cases so every percentage answers the same three-prompt question.
independent_variants = ['minimal', 'fluent_speaker', 'github_searcher']
independent_grid = exact_grid[exact_grid['variant'].isin(independent_variants)].copy()
model_sensitivity = (
    independent_grid.groupby(['language_code', 'service'])
    .agg(available_prompts=('variant', 'nunique'), distinct_forms=('normalized_form', 'nunique'))
    .reset_index()
)
model_sensitivity = model_sensitivity[
    model_sensitivity['available_prompts'].eq(len(independent_variants))
].copy()
model_sensitivity['all_independent_prompts_distinct'] = (
    model_sensitivity['distinct_forms'].eq(len(independent_variants))
)
model_summary = (
    model_sensitivity.groupby('service')
    .agg(
        languages=('language_code', 'nunique'),
        all_distinct_rate=('all_independent_prompts_distinct', 'mean'),
        mean_distinct_forms=('distinct_forms', 'mean'),
    )
    .reset_index()
    .sort_values(['all_distinct_rate', 'mean_distinct_forms'], ascending=False)
)
model_summary['annotation'] = model_summary.apply(
    lambda row: f"{row['all_distinct_rate']:.1%} ({row['mean_distinct_forms']:.2f} mean forms)", axis=1
)
service_order = model_summary['service'].tolist()

model_bar = alt.Chart(model_summary).mark_bar().encode(
    x=alt.X('all_distinct_rate:Q', title='Languages with all three independent prompts distinct',
            axis=alt.Axis(format='.0%', values=[0, .2, .4, .6, .8, 1.0]),
            scale=alt.Scale(domain=[0, 1.22])),
    y=alt.Y('service:N', sort=service_order, title=None),
    color=alt.Color('service:N', legend=None,
                    scale=alt.Scale(domain=list(SERVICE_COLORS),
                                    range=list(SERVICE_COLORS.values()))),
).properties(width=430, height=210, title='Within-model sensitivity across independent prompts')

model_text = model_bar.mark_text(align='left', dx=5, color='black', fontSize=11).encode(
    text='annotation:N'
)
model_panel = model_bar + model_text

prompt_model_structure_chart = (
    alt.hconcat(prompt_panel, model_panel, spacing=45)
    .properties(
        title=alt.TitleParams(
            text='How prompts and models structure exact-form disagreement',
            subtitle=[
                'Left: models compared within each prompt. Right: three independent prompts compared within each model (complete cases).',
                'Exact normalized forms measure stability, not linguistic correctness.',
            ],
            anchor='middle',
        )
    )
    .resolve_scale(color='independent')
    .configure_view(stroke=None)
)
display(prompt_model_structure_chart)
save_chart(
    prompt_model_structure_chart,
    FIGURE_DIR / 'prompt_model_exact_form_disagreement.png',
)

# Combine the two language-level summaries used together in the article.
shape_color_domain = [
    'unanimous', 'near_unanimous_with_outlier',
    'dominant_form_with_alternatives', 'fragmented_disagreement',
]
shape_color_range = ['#2A9D8F', '#76B7B2', '#4C78A8', '#F28E2B']
shape_article = shape_counts[shape_counts['disagreement_shape'].isin(shape_color_domain)].copy()
shape_article_panel = alt.Chart(shape_article).mark_bar().encode(
    x=alt.X('languages:Q', title='Language-code rows'),
    y=alt.Y('label:N', sort=[SHAPE_LABELS[s] for s in shape_color_domain], title=None),
    color=alt.Color('disagreement_shape:N', legend=None,
                    scale=alt.Scale(domain=shape_color_domain, range=shape_color_range)),
)
shape_article_text = shape_article_panel.mark_text(
    align='left', dx=5, color='black', fontSize=12
).encode(text='annotation:N')
shape_article_panel = (shape_article_panel + shape_article_text).properties(
    width=475, height=205, title='A. Structure of translation disagreement'
)

JUDGE_LABELS = {
    'judge_induced_convergence': 'Increased Convergence',
    'limited_judge_change': 'Limited Change',
    'judge_increased_variation': 'Increased Variation',
}
judge_order = [
    'judge_induced_convergence', 'limited_judge_change', 'judge_increased_variation'
]
judge_article = judge_counts.copy()
judge_article['label'] = judge_article['judge_effect'].map(JUDGE_LABELS)
judge_article['pct'] = judge_article['languages'] / len(patterns)
judge_article['annotation'] = judge_article.apply(
    lambda row: f"{row['languages']:,} ({row['pct']:.1%})", axis=1
)
judge_article_panel = alt.Chart(judge_article).mark_bar().encode(
    x=alt.X('languages:Q', title='Language-code rows'),
    y=alt.Y('label:N', sort=[JUDGE_LABELS[key] for key in judge_order], title=None),
    color=alt.Color('judge_effect:N', legend=None,
                    scale=alt.Scale(domain=judge_order,
                                    range=['#2A9D8F', '#A7A7A7', '#F28E2B'])),
)
judge_article_text = judge_article_panel.mark_text(
    align='left', dx=5, color='black', fontSize=12
).encode(text='annotation:N')
judge_article_panel = (judge_article_panel + judge_article_text).properties(
    width=475, height=205, title='B. Effect of the judge prompt on form diversity'
)

disagreement_judge_article_chart = (
    alt.hconcat(shape_article_panel, judge_article_panel, spacing=55)
    .properties(
        title=alt.TitleParams(
            text='Translation disagreement and the judge intervention',
            subtitle=[
                'The judge increased convergence overall but remained generative:',
                '973 of 7,041 populated judge responses (13.8%) introduced a new normalized form.',
            ],
            anchor='middle',
        )
    )
    .resolve_scale(color='independent')
    .configure_view(stroke=None)
)
display(disagreement_judge_article_chart)
save_chart(
    disagreement_judge_article_chart,
    FIGURE_DIR / 'translation_disagreement_and_judge_intervention.png',
)


alt.HConcatChart(...)

alt.HConcatChart(...)

## 5.11 External and Script Evidence

Wikipedia relationships, source retention, and script disagreement remain independent. The heatmap reports how frequently those signals appear within each disagreement shape. It does not treat any signal as proof of correctness, absence, or community acceptance.

In [24]:
evidence = patterns.copy()
evidence['has_source_retention'] = evidence['source_retention_service_count'].gt(0)
evidence['has_singleton_outlier'] = evidence['singleton_outlier_service_count'].gt(0)
evidence['has_prompt_instability'] = evidence['prompt_sensitive_service_count'].gt(0)

signal_map = {
    'has_wikipedia': 'Wikipedia term',
    'has_source_retention': 'Source retention',
    'has_script_disagreement': 'Script disagreement',
    'has_mt_llm_split': 'MT/LLM split',
    'has_singleton_outlier': 'Singleton outlier',
    'has_prompt_instability': 'Prompt instability',
}
evidence_long = (
    evidence.groupby('disagreement_shape')[list(signal_map)].mean()
    .rename(columns=signal_map).reset_index()
    .melt(id_vars='disagreement_shape', var_name='signal', value_name='share')
)
evidence_long['shape_label'] = evidence_long['disagreement_shape'].map(SHAPE_LABELS)

evidence_heat = alt.Chart(evidence_long).mark_rect().encode(
    x=alt.X('signal:N', title=None, axis=alt.Axis(labelAngle=325)),
    y=alt.Y('shape_label:N', sort=[SHAPE_LABELS[s] for s in SHAPE_ORDER], title=None),
    color=alt.Color('share:Q', title='Share', scale=alt.Scale(scheme='blues', domain=[0, 1])),
).properties(width=620, height=230, title='Independent evidence signals by disagreement shape')
evidence_text = evidence_heat.mark_text().encode(
    text=alt.Text('share:Q', format='.0%'),
    color=alt.condition('datum.share > 0.55', alt.value('white'), alt.value('black')),
)
evidence_figure = evidence_heat + evidence_text
display(evidence_figure)
save_chart(evidence_figure, str(FIGURE_DIR / 'evidence_signals_by_disagreement_shape.png'))

alt.LayerChart(...)

## 5.12 Sensitivity Analysis

The primary embedding analysis uses one modal `best_candidate` per service and language. That is a useful summary, but it can conceal prompt variation and make the results depend on a single encoder or unusually influential service. I therefore test four sources of uncertainty:

1. **Input selection:** modal best candidates, the minimal prompt, the three independent prompts pooled without `judge`, the judge prompt alone, and all search-ready prompt cells.
2. **Service influence:** recompute each language's dispersion after omitting one LLM service at a time.
3. **Encoder choice:** compare multilingual MiniLM with LaBSE on the same retained best-candidate strings.
4. **Sampling uncertainty:** bootstrap languages to estimate confidence intervals for the Wikipedia difference, disagreement-shape means, and service-pair distances.

These checks evaluate whether the notebook's rankings and group contrasts survive alternative specifications. They do not identify which translation is correct.


### 5.13 Input Selection: Modal Candidates, Independent Prompts, Judge, and Search-Ready Cells

I rebuild a long table from the prompt-specific source files using the same translation/rationale pairing and Tier 2 language-service exclusions as the primary analysis. `Independent prompts` pools `minimal`, `fluent_speaker`, and `github_searcher`; `Judge only` isolates the synthesis condition. The search-ready view additionally removes cells that retain `Digital Humanities` or `DH`.

For each specification I compute per-language mean pairwise cosine distance. Spearman correlation with the primary modal-candidate ranking tests ordinal stability, while the Wikipedia contrast and disagreement-shape means test whether the substantive group patterns persist.


In [25]:
from scipy.stats import spearmanr
from scripts.analysis.explore_confidence_within_variant import load_variant_df
from scripts.review.translation_classifier import has_source_leakage

LLM_COLS = {
    'Claude': 'claude_translated_term', 'OpenAI': 'openai_translated_term',
    'Gemini': 'gemini_translated_term', 'DeepSeek': 'deepseek_translated_term',
    'Llama': 'llama_translated_term', 'Gemma': 'gemma_translated_term',
    'Qwen': 'qwen_translated_term', 'Mistral': 'mistral_translated_term',
}

prompt_rows = []
for variant in ALL_VARIANTS:
    vdf = load_variant_df(DATA_DIR, TERM_SLUG, variant)
    for _, row in vdf.iterrows():
        for service, column in LLM_COLS.items():
            value = row.get(column)
            if pd.isna(value):
                continue
            text = str(value).strip()
            if not text or text.lower() in {'nan', 'none'}:
                continue
            if (row['language_code'], service) in all_drop_pairs:
                continue
            prompt_rows.append({
                'language_code': row['language_code'],
                'service': service,
                'variant': variant,
                'text': text,
                'has_wikipedia': row['language_code'] in wiki_langs,
                'search_ready': not has_source_leakage(text, TERM),
            })

prompt_long = pd.DataFrame(prompt_rows)
prompt_vecs = embed_with_cache(prompt_long['text'].tolist(), 'translation_prompt_cells')
print(f'Prompt-specific LLM cells retained for sensitivity analysis: {len(prompt_long):,}')

def language_dispersion(frame, vectors):
    rows = []
    for language_code, group in frame.groupby('language_code'):
        if len(group) < 2:
            continue
        distances = pdist(vectors[group.index.to_numpy()], metric='cosine')
        rows.append({
            'language_code': language_code,
            'mean_pairwise_distance': float(distances.mean()),
            'n_cells': len(group),
            'has_wikipedia': bool(group['has_wikipedia'].iloc[0]),
        })
    return pd.DataFrame(rows)

primary_dispersion = scatter_df[['language_code', 'mean_pairwise_distance', 'has_wikipedia']].copy()
primary_dispersion['n_cells'] = np.nan

specifications = {
    'Modal best candidate': (primary_dispersion, None),
    'Minimal only': (prompt_long[prompt_long['variant'].eq('minimal')], prompt_vecs),
    'Independent prompts': (prompt_long[~prompt_long['variant'].eq('judge')], prompt_vecs),
    'Judge only': (prompt_long[prompt_long['variant'].eq('judge')], prompt_vecs),
    'All search-ready cells': (prompt_long[prompt_long['search_ready']], prompt_vecs),
}

dispersion_specs = {}
for label, (frame, vectors) in specifications.items():
    if vectors is None:
        result = frame.copy()
    else:
        # Preserve original vector positions after filtering.
        result = language_dispersion(frame, vectors)
    dispersion_specs[label] = result

primary_rank = primary_dispersion[['language_code', 'mean_pairwise_distance']].rename(
    columns={'mean_pairwise_distance': 'primary_distance'}
)
sensitivity_rows = []
for label, result in dispersion_specs.items():
    merged = primary_rank.merge(
        result[['language_code', 'mean_pairwise_distance', 'has_wikipedia']],
        on='language_code', how='inner',
    )
    rho = spearmanr(merged['primary_distance'], merged['mean_pairwise_distance']).statistic
    wiki_means = merged.groupby('has_wikipedia')['mean_pairwise_distance'].mean()
    sensitivity_rows.append({
        'specification': label,
        'languages': len(merged),
        'spearman_vs_primary': rho,
        'mean_without_wikipedia': wiki_means.get(False, np.nan),
        'mean_with_wikipedia': wiki_means.get(True, np.nan),
        'wikipedia_difference': wiki_means.get(False, np.nan) - wiki_means.get(True, np.nan),
    })

input_sensitivity_df = pd.DataFrame(sensitivity_rows)
display(input_sensitivity_df.round(3))

input_chart_df = input_sensitivity_df.melt(
    id_vars=['specification', 'spearman_vs_primary'],
    value_vars=['mean_without_wikipedia', 'mean_with_wikipedia'],
    var_name='wikipedia_group', value_name='mean_distance',
)
input_chart_df['wikipedia_group'] = input_chart_df['wikipedia_group'].map({
    'mean_without_wikipedia': 'No Wikipedia term',
    'mean_with_wikipedia': 'Wikipedia term',
})
input_sensitivity_chart = alt.Chart(input_chart_df).mark_bar().encode(
    x=alt.X('mean_distance:Q', title='Mean pairwise cosine distance'),
    y=alt.Y('specification:N', sort=input_sensitivity_df['specification'].tolist(), title=None),
    color=alt.Color('wikipedia_group:N', title='Wikipedia evidence',
                    scale=alt.Scale(domain=['Wikipedia term', 'No Wikipedia term'],
                                    range=['#e45756', '#a9a9a9'])),
    yOffset='wikipedia_group:N',
    tooltip=['specification:N', 'wikipedia_group:N', alt.Tooltip('mean_distance:Q', format='.3f'),
             alt.Tooltip('spearman_vs_primary:Q', format='.3f', title='Spearman vs primary')],
).properties(width=520, height=230, title='Wikipedia dispersion contrast across input specifications')
display(input_sensitivity_chart)
save_chart(input_sensitivity_chart, FIGURE_DIR / 'translation_input_sensitivity.png')


Loading cached embeddings: translation_prompt_cells.npy
Prompt-specific LLM cells retained for sensitivity analysis: 26,752


,specification,languages,spearman_vs_primary,mean_without_wikipedia,mean_with_wikipedia,wikipedia_difference
0,Modal best candidate,881,1.000,0.392,0.158,0.233
1,Minimal only,881,0.944,0.400,0.171,0.229
2,Independent prompts,881,0.917,0.383,0.164,0.219
3,Judge only,881,0.636,0.208,0.062,0.146
4,All search-ready cells,881,0.864,0.341,0.141,0.201


alt.Chart(...)

### 5.14 Prompt Variation Within Models and Model Variation Within Prompts

The pooled sensitivity result shows that prompt-specific translations vary, but it combines two sources of movement. I therefore make two crossed comparisons for each language using only the three independent prompts:

- **Across prompts within a model:** how far one service moves when its instructions change.
- **Across models within a prompt:** how far services move while receiving the same instructions.

I first calculate pairwise cosine distances inside each language × service or language × prompt group, then average those group-level distances within each language. This gives services and prompts equal weight despite missing cells. The comparison is descriptive rather than a causal variance decomposition, and it excludes `judge` because that condition receives candidates produced by the other prompts.

The second figure measures each service-prompt cell's distance from its language-specific centroid. It shows where particular model-prompt combinations tend to sit farther from the center of the available independent outputs, but it does not identify those outputs as errors.


In [26]:
INDEPENDENT_VARIANTS = ['minimal', 'fluent_speaker', 'github_searcher']
independent_cells = prompt_long[prompt_long['variant'].isin(INDEPENDENT_VARIANTS)].copy()

def grouped_embedding_distances(frame, group_cols, vectors):
    rows = []
    for keys, group in frame.groupby(group_cols):
        if len(group) < 2:
            continue
        distances = pdist(vectors[group.index.to_numpy()], metric='cosine')
        keys = keys if isinstance(keys, tuple) else (keys,)
        row = dict(zip(group_cols, keys))
        row.update({
            'mean_pairwise_distance': float(distances.mean()),
            'n_cells': len(group),
        })
        rows.append(row)
    return pd.DataFrame(rows)

# Prompt movement inside each service, averaged over services within a language.
within_model_groups = grouped_embedding_distances(
    independent_cells, ['language_code', 'service'], prompt_vecs
)
within_model_language = (
    within_model_groups.groupby('language_code')['mean_pairwise_distance'].mean()
    .rename('across_prompts_within_model')
)

# Model movement inside each prompt, averaged over prompts within a language.
within_prompt_groups = grouped_embedding_distances(
    independent_cells, ['language_code', 'variant'], prompt_vecs
)
within_prompt_language = (
    within_prompt_groups.groupby('language_code')['mean_pairwise_distance'].mean()
    .rename('across_models_within_prompt')
)

crossed_variation = pd.concat([within_model_language, within_prompt_language], axis=1).dropna().reset_index()
crossed_variation['distance_difference'] = (
    crossed_variation['across_models_within_prompt']
    - crossed_variation['across_prompts_within_model']
)
SIMILAR_DISTANCE_THRESHOLD = 0.02
crossed_variation['larger_source'] = np.select(
    [
        crossed_variation['distance_difference'].gt(SIMILAR_DISTANCE_THRESHOLD),
        crossed_variation['distance_difference'].lt(-SIMILAR_DISTANCE_THRESHOLD),
    ],
    ['Across models is larger', 'Across prompts is larger'],
    default='Similar (within 0.02)',
)
crossed_variation.to_csv(
    os.path.join(EVAL_DIR, 'embedding_prompt_model_variation.csv'), index=False
)

variation_long = crossed_variation.melt(
    id_vars='language_code',
    value_vars=['across_prompts_within_model', 'across_models_within_prompt'],
    var_name='comparison', value_name='mean_distance',
)
comparison_labels = {
    'across_prompts_within_model': 'Across prompts within a model',
    'across_models_within_prompt': 'Across models within a prompt',
}
variation_long['comparison_label'] = variation_long['comparison'].map(comparison_labels)
comparison_order = list(comparison_labels.values())
comparison_colors = ['#4C78A8', '#E45756']

variation_box = alt.Chart(variation_long).mark_boxplot(size=42, extent='min-max').encode(
    x=alt.X('mean_distance:Q', title='Mean pairwise cosine distance per language'),
    y=alt.Y('comparison_label:N', sort=comparison_order, title=None),
    color=alt.Color(
        'comparison_label:N', legend=None,
        scale=alt.Scale(domain=comparison_order, range=comparison_colors),
    ),
).properties(
    width=650, height=125,
    title='Prompt variation within models versus model variation within prompts',
)

source_order = ['Across models is larger', 'Across prompts is larger', 'Similar (within 0.02)']
source_counts = (
    crossed_variation['larger_source'].value_counts().reindex(source_order, fill_value=0)
    .rename_axis('larger_source').reset_index(name='languages')
)
source_counts['share'] = source_counts['languages'] / len(crossed_variation)
source_counts['annotation'] = source_counts.apply(
    lambda row: f"{row['languages']:,} ({row['share']:.1%})", axis=1
)
source_x_max = float(source_counts['languages'].max() * 1.12)
source_bar_base = alt.Chart(source_counts).mark_bar().encode(
    x=alt.X('languages:Q', title='Languages', scale=alt.Scale(domain=[0, source_x_max])),
    y=alt.Y('larger_source:N', sort=source_order, title=None),
    color=alt.Color(
        'larger_source:N', legend=None,
        scale=alt.Scale(
            domain=source_order, range=['#E45756', '#4C78A8', '#9D9D9D']
        ),
    ),
)
source_bar_text = source_bar_base.mark_text(align='left', dx=5, color='black').encode(
    text='annotation:N'
)
source_bar = (source_bar_base + source_bar_text).properties(
    width=650, height=105,
    title='Which comparison produces the larger average distance?',
)
crossed_variation_chart = (
    alt.vconcat(variation_box, source_bar, spacing=28)
    .resolve_scale(color='independent')
    .configure_view(stroke=None)
)
display(crossed_variation_chart)
save_chart(
    crossed_variation_chart,
    FIGURE_DIR / 'prompt_vs_model_embedding_variation.png',
)

# Distance of every independent service-prompt cell from its language centroid.
centroid_rows = []
for language_code, group in independent_cells.groupby('language_code'):
    positions = group.index.to_numpy()
    vectors = prompt_vecs[positions]
    centroid = vectors.mean(axis=0)
    centroid_norm = np.linalg.norm(centroid)
    if centroid_norm == 0:
        continue
    centroid = centroid / centroid_norm
    distances = 1 - vectors @ centroid
    for (_, row), distance in zip(group.iterrows(), distances):
        centroid_rows.append({
            'language_code': language_code,
            'service': row['service'],
            'variant': row['variant'],
            'centroid_distance': float(distance),
        })

centroid_cells = pd.DataFrame(centroid_rows)
centroid_summary = (
    centroid_cells.groupby(['service', 'variant'])['centroid_distance']
    .agg(mean_distance='mean', median_distance='median', languages='size')
    .reset_index()
)
centroid_summary.to_csv(
    os.path.join(EVAL_DIR, 'embedding_service_prompt_centroid_distances.csv'), index=False
)
service_order = list(LLM_COLS)
centroid_heatmap_base = alt.Chart(centroid_summary).mark_rect().encode(
    x=alt.X(
        'variant:N', sort=INDEPENDENT_VARIANTS, title='Independent prompt',
        axis=alt.Axis(labelExpr="replace(datum.label, '_', ' ')", labelAngle=0),
    ),
    y=alt.Y('service:N', sort=service_order, title=None),
    color=alt.Color(
        'mean_distance:Q', title='Mean distance', scale=alt.Scale(scheme='yelloworangered')
    ),
)
centroid_heatmap_text = centroid_heatmap_base.mark_text(fontSize=12).encode(
    text=alt.Text('mean_distance:Q', format='.3f'),
    color=alt.condition('datum.mean_distance > 0.215', alt.value('white'), alt.value('black')),
)
centroid_heatmap = (centroid_heatmap_base + centroid_heatmap_text).properties(
    width=480, height=300,
    title='Average distance from each language’s independent-output centroid',
).configure_view(stroke=None)
display(centroid_heatmap)
save_chart(
    centroid_heatmap,
    FIGURE_DIR / 'service_prompt_centroid_distance_heatmap.png',
)

print(f'Languages in crossed comparison: {len(crossed_variation):,}')
display(
    variation_long.groupby('comparison_label')['mean_distance']
    .agg(['count', 'mean', 'median']).reindex(comparison_order).round(3)
)
display(source_counts)
display(centroid_summary.sort_values('mean_distance', ascending=False).round(3))


alt.VConcatChart(...)

alt.LayerChart(...)

Languages in crossed comparison: 881


,count,mean,median
comparison_label,,,
Across prompts within a model,881,0.264,0.269
Across models within a prompt,881,0.378,0.407


,larger_source,languages,share,annotation
0,Across models is larger,817,0.927355,817 (92.7%)
1,Across prompts is larger,15,0.017026,15 (1.7%)
2,Similar (within 0.02),49,0.055619,49 (5.6%)


,service,variant,mean_distance,median_distance,languages
22,Qwen,github_searcher,0.274,0.270,840
17,Mistral,minimal,0.262,0.254,807
23,Qwen,minimal,0.261,0.253,837
21,Qwen,fluent_speaker,0.261,0.253,841
12,Llama,fluent_speaker,0.253,0.230,849
13,Llama,github_searcher,0.242,0.231,760
14,Llama,minimal,0.241,0.221,760
16,Mistral,github_searcher,0.237,0.234,859
9,Gemma,fluent_speaker,0.227,0.212,830
11,Gemma,minimal,0.227,0.214,817


### 5.15 Final Observed Similarity With the Judge Included

The independent-prompt comparison is the cleaner estimate of prompt and model variation because none of those outputs receives another candidate as evidence. For the final state of the pipeline, however, I also calculate the same crossed distances across all four prompts, including `judge`.

I summarize each language with a final observed similarity metric: one minus the mean pairwise cosine distance across every retained LLM service × prompt translation cell. A value closer to one means the complete output grid occupies a tighter region of this embedding space. This remains a geometric summary rather than a measure of correctness. Comparing the independent grid with the all-prompt grid makes clear whether adding the dependent judge condition compresses or expands the final observed translation space.


In [27]:
def crossed_language_variation(frame, vectors):
    within_service = grouped_embedding_distances(
        frame, ['language_code', 'service'], vectors
    )
    within_variant = grouped_embedding_distances(
        frame, ['language_code', 'variant'], vectors
    )
    service_means = (
        within_service.groupby('language_code')['mean_pairwise_distance'].mean()
        .rename('across_prompts_within_model')
    )
    variant_means = (
        within_variant.groupby('language_code')['mean_pairwise_distance'].mean()
        .rename('across_models_within_prompt')
    )
    return pd.concat([service_means, variant_means], axis=1).dropna().reset_index()

all_prompt_variation = crossed_language_variation(prompt_long, prompt_vecs)
all_prompt_variation['distance_difference'] = (
    all_prompt_variation['across_models_within_prompt']
    - all_prompt_variation['across_prompts_within_model']
)
all_prompt_variation['larger_source'] = np.select(
    [
        all_prompt_variation['distance_difference'].gt(SIMILAR_DISTANCE_THRESHOLD),
        all_prompt_variation['distance_difference'].lt(-SIMILAR_DISTANCE_THRESHOLD),
    ],
    ['Across models is larger', 'Across prompts is larger'],
    default='Similar (within 0.02)',
)

def full_grid_similarity(frame, vectors, label):
    dispersion = grouped_embedding_distances(frame, ['language_code'], vectors)
    return dispersion[['language_code', 'n_cells', 'mean_pairwise_distance']].rename(columns={
        'n_cells': f'{label}_cells',
        'mean_pairwise_distance': f'{label}_distance',
    }).assign(**{f'{label}_similarity': lambda data: 1 - data[f'{label}_distance']})

independent_similarity = full_grid_similarity(independent_cells, prompt_vecs, 'independent')
all_prompt_similarity = full_grid_similarity(prompt_long, prompt_vecs, 'all_prompts')
translation_grid_similarity = independent_similarity.merge(
    all_prompt_similarity, on='language_code', how='inner'
)
translation_grid_similarity['judge_similarity_change'] = (
    translation_grid_similarity['all_prompts_similarity']
    - translation_grid_similarity['independent_similarity']
)
translation_grid_similarity.to_csv(
    os.path.join(EVAL_DIR, 'translation_full_grid_similarity.csv'), index=False
)
all_prompt_variation.to_csv(
    os.path.join(EVAL_DIR, 'embedding_prompt_model_variation_with_judge.csv'), index=False
)

all_crossed_long = all_prompt_variation.melt(
    id_vars='language_code',
    value_vars=['across_prompts_within_model', 'across_models_within_prompt'],
    var_name='comparison', value_name='mean_distance',
)
all_crossed_long['comparison_label'] = all_crossed_long['comparison'].map(comparison_labels)
all_crossed_box = alt.Chart(all_crossed_long).mark_boxplot(size=42, extent='min-max').encode(
    x=alt.X('mean_distance:Q', title='Mean pairwise cosine distance per language'),
    y=alt.Y('comparison_label:N', sort=comparison_order, title=None),
    color=alt.Color(
        'comparison_label:N', legend=None,
        scale=alt.Scale(domain=comparison_order, range=comparison_colors),
    ),
).properties(
    width=650, height=125,
    title='Prompt and model variation with the judge included',
)

similarity_long = translation_grid_similarity.melt(
    id_vars='language_code',
    value_vars=['independent_similarity', 'all_prompts_similarity'],
    var_name='scope', value_name='mean_similarity',
)
similarity_labels = {
    'independent_similarity': 'Independent prompts only',
    'all_prompts_similarity': 'All prompts including judge',
}
similarity_long['scope_label'] = similarity_long['scope'].map(similarity_labels)
similarity_order = list(similarity_labels.values())
similarity_box = alt.Chart(similarity_long).mark_boxplot(size=42, extent='min-max').encode(
    x=alt.X('mean_similarity:Q', title='Mean pairwise cosine similarity per language'),
    y=alt.Y('scope_label:N', sort=similarity_order, title=None),
    color=alt.Color(
        'scope_label:N', legend=None,
        scale=alt.Scale(domain=similarity_order, range=['#72B7B2', '#F2CF5B']),
    ),
).properties(
    width=650, height=125,
    title='Final translation-grid similarity before and after adding the judge',
)
translation_final_similarity_chart = (
    alt.vconcat(all_crossed_box, similarity_box, spacing=28)
    .resolve_scale(color='independent')
    .configure_view(stroke=None)
)
display(translation_final_similarity_chart)
save_chart(
    translation_final_similarity_chart,
    FIGURE_DIR / 'translation_similarity_with_judge.png',
)

print('All-prompt crossed variation:')
display(
    all_crossed_long.groupby('comparison_label')['mean_distance']
    .agg(['count', 'mean', 'median']).reindex(comparison_order).round(3)
)
print('Final observed similarity:')
display(
    similarity_long.groupby('scope_label')['mean_similarity']
    .agg(['count', 'mean', 'median']).reindex(similarity_order).round(3)
)
print('Effect of adding judge outputs:')
display(translation_grid_similarity['judge_similarity_change'].describe().round(3))
display(all_prompt_variation['larger_source'].value_counts().rename_axis('comparison').to_frame('languages'))


alt.VConcatChart(...)

All-prompt crossed variation:


,count,mean,median
comparison_label,,,
Across prompts within a model,881,0.280,0.291
Across models within a prompt,881,0.334,0.352


Final observed similarity:


,count,mean,median
scope_label,,,
Independent prompts only,881,0.627,0.599
All prompts including judge,881,0.659,0.637


Effect of adding judge outputs:


count    881.000
mean       0.032
std        0.022
min       -0.053
25%        0.017
50%        0.031
75%        0.048
max        0.089
Name: judge_similarity_change, dtype: float64

,languages
comparison,
Across models is larger,669
Similar (within 0.02),162
Across prompts is larger,50


### 5.16 Leave-One-Service-Out Stability

Pairwise dispersion does not require a centroid, but one service can still contribute disproportionately to a language's apparent instability. I remove each LLM service in turn and compare the resulting language ranking with the full eight-service result. I also measure the average change in dispersion: a negative value means removing that service makes languages look more tightly clustered.


In [28]:
llm_primary = trans_df[trans_df['service'].isin(LLM_COLS)].copy()
full_primary = primary_dispersion[['language_code', 'mean_pairwise_distance']].rename(
    columns={'mean_pairwise_distance': 'full_distance'}
)

loo_rows = []
loo_language_rows = []
for omitted in LLM_COLS:
    subset = llm_primary[~llm_primary['service'].eq(omitted)]
    subset_result = language_dispersion(subset, trans_vecs)
    comparison = full_primary.merge(subset_result, on='language_code', how='inner')
    comparison['distance_change'] = comparison['mean_pairwise_distance'] - comparison['full_distance']
    rho = spearmanr(comparison['full_distance'], comparison['mean_pairwise_distance']).statistic
    loo_rows.append({
        'omitted_service': omitted,
        'languages': len(comparison),
        'spearman_vs_full': rho,
        'mean_distance_change': comparison['distance_change'].mean(),
        'mean_absolute_change': comparison['distance_change'].abs().mean(),
    })
    comparison['omitted_service'] = omitted
    loo_language_rows.append(comparison)

loo_summary_df = pd.DataFrame(loo_rows).sort_values('mean_absolute_change', ascending=False)
loo_language_df = pd.concat(loo_language_rows, ignore_index=True)
display(loo_summary_df.round(4))

loo_chart = alt.Chart(loo_summary_df).mark_bar().encode(
    x=alt.X('mean_distance_change:Q', title='Mean change after omitting service'),
    y=alt.Y('omitted_service:N', sort=alt.SortField('mean_absolute_change', order='descending'), title=None),
    color=alt.condition(alt.datum.mean_distance_change < 0, alt.value('#4c78a8'), alt.value('#e45756')),
    tooltip=['omitted_service:N', alt.Tooltip('spearman_vs_full:Q', format='.3f'),
             alt.Tooltip('mean_distance_change:Q', format='+.4f'),
             alt.Tooltip('mean_absolute_change:Q', format='.4f')],
).properties(width=500, height=230, title='Influence of each service on per-language dispersion')
display(loo_chart)
save_chart(loo_chart, FIGURE_DIR / 'translation_leave_one_service_out.png')

largest_loo_changes = (
    loo_language_df.assign(abs_change=lambda d: d['distance_change'].abs())
    .nlargest(20, 'abs_change')
    .merge(detail_df[['language_code', 'language_name']].drop_duplicates('language_code'),
           on='language_code', how='left')
)
display(largest_loo_changes[[
    'language_code', 'language_name', 'omitted_service', 'full_distance',
    'mean_pairwise_distance', 'distance_change',
]].round(4))


,omitted_service,languages,spearman_vs_full,mean_distance_change,mean_absolute_change
4,Llama,881,0.9639,-0.0137,0.0300
7,Mistral,881,0.9708,-0.0130,0.0274
6,Qwen,881,0.9727,-0.0151,0.0269
1,OpenAI,881,0.9685,0.0101,0.0259
5,Gemma,881,0.9695,-0.0060,0.0254
3,DeepSeek,881,0.9748,0.0116,0.0247
0,Claude,881,0.9787,0.0128,0.0236
2,Gemini,881,0.9791,0.0131,0.0234


alt.Chart(...)

,language_code,language_name,omitted_service,full_distance,mean_pairwise_distance,distance_change
0,rob,Tae',Qwen,0.3866,0.1305,-0.2562
1,thl,Dangaura Tharu,Llama,0.2502,0.0486,-0.2016
2,zh-tw,Traditional Chinese,Llama,0.3791,0.1799,-0.1992
3,jml,Jumli,Llama,0.3474,0.1500,-0.1974
4,hak,Hakka Chinese,Llama,0.2294,0.0400,-0.1894
5,ett,Etruscan,Qwen,0.3442,0.1616,-0.1826
6,zh,Chinese,Llama,0.2260,0.0437,-0.1822
7,dum,Middle Dutch,Gemma,0.3541,0.1722,-0.1819
8,thr,Rana Tharu,Llama,0.3177,0.1375,-0.1802
9,ude,Udihe,Llama,0.3629,0.1846,-0.1783


### 5.17 Encoder and Sampling Sensitivity

MiniLM is not a neutral measurement instrument. I re-embed the same retained best-candidate strings with `sentence-transformers/LaBSE`, then compare language-dispersion and service-distance rankings. LaBSE is used as a sensitivity model, not as a new ground truth.

Finally, I bootstrap language rows to place 95% intervals around the main group contrasts. Resampling languages preserves each language as the unit of inference and makes the small Wikipedia, unanimous, and near-unanimous groups visible in the uncertainty estimates.


In [29]:
ALT_EMBED_MODEL = 'sentence-transformers/LaBSE'
alt_model = SentenceTransformer(ALT_EMBED_MODEL)

def embed_with_model_cache(texts, embedding_model, cache_name, batch_size=128):
    cache_path = CACHE_DIR / f'{cache_name}.npy'
    if cache_path.exists():
        cached = np.load(cache_path)
        if len(cached) == len(texts):
            print(f'Loading cached embeddings: {cache_path.name}')
            return cached
    print(f'Encoding {len(texts):,} texts with {ALT_EMBED_MODEL} → {cache_path.name}')
    vectors = embedding_model.encode(
        texts, batch_size=batch_size, show_progress_bar=True,
        convert_to_numpy=True, normalize_embeddings=True,
    )
    np.save(cache_path, vectors)
    return vectors

labse_vecs = embed_with_model_cache(
    trans_df['best_candidate'].tolist(), alt_model, 'translation_vecs_labse', batch_size=64,
)
labse_dispersion = language_dispersion(llm_primary, labse_vecs)
encoder_comparison = primary_rank.merge(
    labse_dispersion[['language_code', 'mean_pairwise_distance']],
    on='language_code', suffixes=('_minilm', '_labse'),
)
encoder_rho = spearmanr(
    encoder_comparison['primary_distance'], encoder_comparison['mean_pairwise_distance']
).statistic
print(f'Language-dispersion rank correlation, MiniLM vs LaBSE: {encoder_rho:.3f}')

def service_pair_table(frame, vectors):
    rows = []
    for language_code, group in frame.groupby('language_code'):
        services = group['service'].tolist()
        positions = group.index.to_numpy()
        for i in range(len(group)):
            for j in range(i + 1, len(group)):
                a, b = sorted([services[i], services[j]])
                distance = float(1 - np.dot(vectors[positions[i]], vectors[positions[j]]))
                rows.append({'language_code': language_code, 'service_a': a, 'service_b': b,
                             'distance': distance})
    return pd.DataFrame(rows)

minilm_pairs = service_pair_table(llm_primary, trans_vecs)
labse_pairs = service_pair_table(llm_primary, labse_vecs)
pair_model_comparison = (
    minilm_pairs.groupby(['service_a', 'service_b'])['distance'].mean().rename('minilm')
    .to_frame().join(
        labse_pairs.groupby(['service_a', 'service_b'])['distance'].mean().rename('labse')
    ).reset_index()
)
pair_rho = spearmanr(pair_model_comparison['minilm'], pair_model_comparison['labse']).statistic
print(f'Service-pair distance rank correlation, MiniLM vs LaBSE: {pair_rho:.3f}')
display(pair_model_comparison.sort_values('minilm').round(3))

# Bootstrap language-level contrasts.
rng = np.random.default_rng(42)
BOOTSTRAP_REPS = 2000

def bootstrap_mean_ci(values, reps=BOOTSTRAP_REPS):
    values = np.asarray(values, dtype=float)
    draws = rng.choice(values, size=(reps, len(values)), replace=True).mean(axis=1)
    return float(values.mean()), float(np.quantile(draws, .025)), float(np.quantile(draws, .975))

bootstrap_rows = []

# Direct interval for the Wikipedia contrast (no-Wikipedia minus Wikipedia).
without_wiki = scatter_df.loc[~scatter_df['has_wikipedia'], 'mean_pairwise_distance'].to_numpy()
with_wiki = scatter_df.loc[scatter_df['has_wikipedia'], 'mean_pairwise_distance'].to_numpy()
wiki_difference_draws = np.array([
    rng.choice(without_wiki, len(without_wiki), replace=True).mean()
    - rng.choice(with_wiki, len(with_wiki), replace=True).mean()
    for _ in range(BOOTSTRAP_REPS)
])
wiki_difference_ci = pd.DataFrame([{
    'contrast': 'No Wikipedia term minus Wikipedia term',
    'estimate': without_wiki.mean() - with_wiki.mean(),
    'ci_low': np.quantile(wiki_difference_draws, .025),
    'ci_high': np.quantile(wiki_difference_draws, .975),
}])
print('Bootstrap interval for the Wikipedia dispersion difference:')
display(wiki_difference_ci.round(3))

for has_wikipedia, group in scatter_df.groupby('has_wikipedia'):
    estimate, low, high = bootstrap_mean_ci(group['mean_pairwise_distance'])
    bootstrap_rows.append({
        'metric': 'Wikipedia evidence',
        'group': 'Wikipedia term' if has_wikipedia else 'No Wikipedia term',
        'n_languages': len(group), 'estimate': estimate, 'ci_low': low, 'ci_high': high,
    })

shape_bootstrap = patterns[['language_code', 'disagreement_shape']].merge(
    scatter_df[['language_code', 'mean_pairwise_distance']], on='language_code', how='inner'
)
for shape, group in shape_bootstrap.groupby('disagreement_shape'):
    estimate, low, high = bootstrap_mean_ci(group['mean_pairwise_distance'])
    bootstrap_rows.append({
        'metric': 'Disagreement shape', 'group': SHAPE_LABELS.get(shape, shape),
        'n_languages': len(group), 'estimate': estimate, 'ci_low': low, 'ci_high': high,
    })

bootstrap_df = pd.DataFrame(bootstrap_rows)
display(bootstrap_df.round(3))

# Bootstrap each service-pair mean over the languages where both services appear.
service_pair_ci_rows = []
for (service_a, service_b), group in minilm_pairs.groupby(['service_a', 'service_b']):
    estimate, low, high = bootstrap_mean_ci(group['distance'])
    service_pair_ci_rows.append({
        'service_a': service_a, 'service_b': service_b,
        'n_languages': group['language_code'].nunique(),
        'estimate': estimate, 'ci_low': low, 'ci_high': high,
    })
service_pair_ci_df = pd.DataFrame(service_pair_ci_rows).sort_values('estimate')
print('Bootstrap intervals for MiniLM service-pair distances:')
display(service_pair_ci_df.round(3))

bootstrap_chart = alt.Chart(bootstrap_df).mark_point(filled=True, size=70).encode(
    x=alt.X('estimate:Q', title='Mean pairwise cosine distance'),
    y=alt.Y('group:N', title=None),
    color=alt.Color('metric:N', title=None, scale=alt.Scale(scheme='tableau10')),
    tooltip=['metric:N', 'group:N', 'n_languages:Q',
             alt.Tooltip('estimate:Q', format='.3f'),
             alt.Tooltip('ci_low:Q', format='.3f'), alt.Tooltip('ci_high:Q', format='.3f')],
).properties(width=520, height=230, title='Bootstrap uncertainty for principal dispersion comparisons')
bootstrap_error = alt.Chart(bootstrap_df).mark_rule().encode(
    x='ci_low:Q', x2='ci_high:Q', y=alt.Y('group:N', title=None), color='metric:N'
)
bootstrap_figure = bootstrap_error + bootstrap_chart
display(bootstrap_figure)
save_chart(bootstrap_figure, FIGURE_DIR / 'translation_dispersion_bootstrap_intervals.png')


Loading cached embeddings: translation_vecs_labse.npy
Language-dispersion rank correlation, MiniLM vs LaBSE: 0.717
Service-pair distance rank correlation, MiniLM vs LaBSE: 0.835


,service_a,service_b,minilm,labse
5,Claude,OpenAI,0.247,0.299
16,Gemini,OpenAI,0.261,0.313
0,Claude,DeepSeek,0.263,0.335
1,Claude,Gemini,0.270,0.338
7,DeepSeek,Gemini,0.273,0.352
11,DeepSeek,OpenAI,0.297,0.344
8,DeepSeek,Gemma,0.372,0.501
13,Gemini,Gemma,0.374,0.474
18,Gemma,Llama,0.384,0.547
2,Claude,Gemma,0.386,0.501


Bootstrap interval for the Wikipedia dispersion difference:


,contrast,estimate,ci_low,ci_high
0,No Wikipedia term minus Wikipedia term,0.233,0.196,0.268


,metric,group,n_languages,estimate,ci_low,ci_high
0,Wikipedia evidence,No Wikipedia term,841,0.392,0.382,0.401
1,Wikipedia evidence,Wikipedia term,40,0.158,0.125,0.193
2,Disagreement shape,Dominant Form With Alternatives,128,0.224,0.199,0.249
3,Disagreement shape,Fragmented Disagreement,746,0.411,0.401,0.421
4,Disagreement shape,Near Unanimous With Outlier,2,0.187,0.062,0.312
5,Disagreement shape,Unanimous,5,0.011,0.000,0.034


Bootstrap intervals for MiniLM service-pair distances:


,service_a,service_b,n_languages,estimate,ci_low,ci_high
5,Claude,OpenAI,864,0.247,0.229,0.264
16,Gemini,OpenAI,853,0.261,0.243,0.280
0,Claude,DeepSeek,870,0.263,0.247,0.280
1,Claude,Gemini,860,0.270,0.253,0.287
7,DeepSeek,Gemini,860,0.273,0.255,0.290
11,DeepSeek,OpenAI,864,0.297,0.277,0.315
8,DeepSeek,Gemma,825,0.372,0.354,0.389
13,Gemini,Gemma,814,0.374,0.356,0.392
18,Gemma,Llama,804,0.384,0.367,0.400
2,Claude,Gemma,826,0.386,0.369,0.404


alt.LayerChart(...)

## 5.18 Interpretation and Robustness Boundaries

The combined analysis separates several questions that a single agreement score would collapse:

1. **Degree:** are the usable strings exact, near-form, or substantively different?
2. **Shape:** is disagreement fragmented, or is there a dominant form with a small number of alternatives?
3. **Participants:** is variation concentrated among API services, local models, machine translation systems, or one outlier?
4. **Trajectory:** does changing the prompt preserve, expand, or compress the available forms?
5. **Context:** do Wikipedia evidence, source retention, or script disagreement accompany the pattern?

Embedding distance adds a continuous comparison among non-identical strings, but the current specification still depends on one multilingual encoder and one resolved best candidate per service. The strongest claims are those that also appear in the transparent string and prompt comparisons. The sensitivity analyses above test prompt selection, individual-service influence, encoder choice, and sampling uncertainty. They do not turn embedding distance into a correctness measure; they show which descriptive findings are stable under reasonable alternatives.
